# 🤖 Qwen 情感推論器（微調模型版 / Google Colab）

**角色：Inference Only**

使用你已微調並合併好的 `Qwen2.5` 模型，透過 **vLLM** 對新聞批次推論 1–10 情感分數。
本程式**只做推論**，不含 Gemini 一致性評估與圖表比對（如需評估請參考原始訓練用notebook）。

---

| 項目 | 說明 |
|------|------|
| **輸入** | 你的新聞資料 `.jsonl`（每行需含 `stock`、`input` 欄位）|
| **輸出** | `qwen_predictions.jsonl`（每筆多一個 `output` 欄位，含 `sentiment_score` 與 `confidence`）|
| **模型** | `/content/drive/MyDrive/qwen2.5/qwen_finetuned_merged`（本機微調合併模型，非量化）|
| **推薦 GPU** | A100 40GB / L4 24GB / T4 16GB（需調整 `MAX_MODEL_LEN`）|

> ⚠️ **執行前請先確認**：Runtime → Change runtime type → **GPU**


In [1]:
from google.colab import drive
drive.mount('/content/drive')

'''
function ConnectButton(){
    console.log("Connect pushed");
    document.querySelector("#top-toolbar > colab-connect-button").shadowRoot.querySelector("#connect").click()
}
setInterval(ConnectButton, 60000);

for (let i = 1; i < 99999; i++) window.clearInterval(i);
console.log("已清除所有自動執行腳本");
'''


Mounted at /content/drive


'\nfunction ConnectButton(){\n    console.log("Connect pushed");\n    document.querySelector("#top-toolbar > colab-connect-button").shadowRoot.querySelector("#connect").click()\n}\nsetInterval(ConnectButton, 60000);\n\nfor (let i = 1; i < 99999; i++) window.clearInterval(i);\nconsole.log("已清除所有自動執行腳本");\n'

## 🖥️ Step 0 — 確認 GPU 環境

In [2]:
!nvidia-smi
print()

import subprocess
result = subprocess.run(['nvidia-smi', '--query-gpu=name,memory.total', '--format=csv,noheader'],
                        capture_output=True, text=True)
gpu_info = result.stdout.strip()
print(f'🎮 GPU：{gpu_info}')

# 根據 GPU 顯存給出建議設定（未量化模型較吃顯存，數值已比 AWQ 版保守）
vram_mb = int(result.stdout.split(',')[1].strip().replace(' MiB', ''))
if vram_mb >= 35000:
    print('✅ 建議設定：MAX_MODEL_LEN = 8192，BATCH_SIZE = 24')
elif vram_mb >= 20000:
    print('✅ 建議設定：MAX_MODEL_LEN = 6144，BATCH_SIZE = 16')
else:
    print('⚠️  建議設定：MAX_MODEL_LEN = 4096，BATCH_SIZE = 8（T4 顯存有限，未量化模型可能吃緊）')


Fri Jul 17 12:12:32 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.82.07              Driver Version: 580.82.07      CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  NVIDIA L4                      Off |   00000000:00:03.0 Off |                    0 |
| N/A   44C    P8             12W /   72W |       0MiB /  23034MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

## 📦 Step 1 — 安裝 vLLM 環境

> ⏱️ 首次安裝約需 **3–5 分鐘**（本模型未量化，不需安裝 autoawq）

In [ ]:
!pip install vllm==0.9.0 -q
!pip install bitsandbytes>=0.45.0 -q
print('✅ vLLM + bitsandbytes 安裝完成')


   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 377.2/377.2 MB 2.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 100.3/100.3 kB 11.0 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 111.0/111.0 kB 13.5 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 3.9/3.9 MB 132.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 87.6/87.6 kB 9.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 865.0/865.0 MB 1.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 3.5/3.5 MB 10.3 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 7.4/7.4 MB 124.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 31.5/31.5 MB 79.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 5.8/5.8 MB 115.4 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 393.1/393.1 MB 2.4 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 8.9/8.9 MB 149.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 23.7/23.

In [ ]:
!pip install transformers==4.51.3 accelerate


   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 10.4/10.4 MB 151.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 566.4/566.4 kB 50.2 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 3.1/3.1 MB 129.7 MB/s eta 0:00:00
  Attempting uninstall: huggingface-hub
    Found existing installation: huggingface_hub 1.20.1
    Uninstalling huggingface_hub-1.20.1:
      Successfully uninstalled huggingface_hub-1.20.1
  Attempting uninstall: tokenizers
    Found existing installation: tokenizers 0.22.2
    Uninstalling tokenizers-0.22.2:
      Successfully uninstalled tokenizers-0.22.2
  Attempting uninstall: transformers
    Found existing installation: transformers 5.12.1
    Uninstalling transformers-5.12.1:
      Successfully uninstalled transformers-5.12.1
ERROR: pip's dependency resolver does not currently take into account all the packages that are installed. This behaviour is the source of the following dependency conflicts.
gradio 6.19.0 requires huggingface-hub<2.0,>=

## ⚙️ Step 2 — 設定區

> 根據 Step 0 的 GPU 建議調整 `MAX_MODEL_LEN` 與 `BATCH_SIZE`

In [ ]:
# ── 模型（你的微調合併模型，本機路徑，非 HuggingFace Hub）───────
MODEL_ID = '/content/drive/MyDrive/qwen2.5/qwen_finetuned_merged'

# ── GPU 設定（根據顯存調整，未量化模型比 AWQ 版更吃顯存）──────
BATCH_SIZE      = 16    # A100: 24 / L4: 16 / T4: 8
MAX_MODEL_LEN   = 8192  # A100: 8192 / L4: 6144 / T4: 4096
GPU_MEMORY_UTIL = 0.90  # GPU 顯存使用率上限

print(f'✅ 設定完成')
print(f'   模型      : {MODEL_ID}')
print(f'   批次大小  : {BATCH_SIZE}')
print(f'   最大長度  : {MAX_MODEL_LEN}')
print(f'   顯存上限  : {GPU_MEMORY_UTIL * 100:.0f}%')


✅ 設定完成
   模型      : /content/drive/MyDrive/qwen2.5/qwen_finetuned_merged
   批次大小  : 16
   最大長度  : 8192
   顯存上限  : 90%


## 🧠 Step 3 — System Prompt 定義

> 與訓練時使用的評分標準保持一致，確保推論結果符合微調時學到的邏輯。

In [ ]:
import json
import os

BASE_SYSTEM_PROMPT = """
你是一位台灣股市量化分析師。
請分析以下新聞對「指定股票」的股價情緒影響，給出 1 到 10 的整數情緒分數。

【判斷維度（請綜合考量）】
- 影響程度：消息對基本面（營收、獲利、訂單、產能、競爭力）的衝擊大小
- 確定性：是「已發生/已證實」還是「預期/傳聞/可能」
- 影響範圍：僅該公司、整個產業、還是大盤層級
- 時間框架：短期（1個月內反映）還是長期（需數季才顯現）

【評分標準與範例】

 1 分：重大利空，股價可能大跌
   例：財務造假、重大違約/跳票、巨額虧損且超乎預期、下市/重整風險、
       董座或高層涉及重大刑事案件、工廠重大火災或停產且復原時間長、
       訴訟敗訴需鉅額賠償。

 2 分：明顯利空
   例：單季獲利或營收明顯不如市場預期、法說會大幅下修財測、
       重大客戶/訂單流失或延遲、信評或外資大幅調降評等與目標價、
       裁員或關廠等成本結構惡化訊號。

 3 分：輕微利空
   例：營收月減或年減但在合理範圍內、外資小幅調降目標價、
       原物料成本上升但公司表示可部分轉嫁、產業面出現溫和的負面雜音。

 4 分：偏空中性，預期有小幅負面壓力
   例：消息本身偏負面但對基本面影響極小或屬一次性費用、
       同業出現利空但對該公司影響有限、技術面或籌碼面的輕微負面訊息。

 5 分：完全中性，無明確影響
   例：例行性公告（股東會召開、董監事補選、一般人事異動）、
       與股價無直接關聯的企業形象/公益新聞、單純背景報導不含新資訊。

 6 分：偏多中性，長期可能正向但短期難反映
   例：長期利多但短期難反映在財報上（如簽署MOU、初期合作意向）、
       產業趨勢面偏正向但該公司受惠程度尚不明確、小幅度的正面雜音。

 7 分：輕微利多，已有可觀察到的正面訊號
   例：營收月增或年增且符合或略優於預期、取得新客戶或小型新訂單、
       外資小幅調升目標價、毛利率小幅改善。

 8 分：明顯利多
   例：單季獲利或營收明顯優於市場預期、法說會上修財測、
       取得指標性大客戶訂單、外資大幅調升評等或目標價、新產品/新產能開出。

 9 分：強力利多，股價可能大漲
   例：取得遠超預期的鉅額訂單或長約、重大技術突破並開始量產、
       公司大幅上修財測且幅度顯著、獲利創歷史新高且超乎市場預期甚多。

10 分：極度利多，歷史性重大正面事件
   例：被收購且收購價大幅溢價、與重量級企業達成排他性策略合作、
       公司營運模式出現結構性轉變且確定性極高、其他足以改變公司基本面定位的重大事件。

【特殊情況處理】
- 若新聞內容與該股票無直接或間接關聯，給 5 分，並將 confidence 設為1。
- 若新聞為「傳聞」、「市場預期」、「分析師臆測」而非已證實事實，
- 若新聞同時包含利多與利空訊息，請綜合評估「淨影響方向與強度」後給分。

【信心度判斷原則（請依規則逐步調整）】

請先設定基準信心度為 0.85，然後依下列條件加減：

【提高信心度】
+0.05：有明確數據（如營收、EPS、訂單金額）
+0.05：事件為「已發生」且被確認（非預期或推測）

【降低信心度】
-0.10：新聞包含「可能、預期、傳聞、法人看法」
-0.10：影響需經推論（非直接影響公司財務或營運）
-0.15：同時包含利多與利空訊息（需綜合判斷）
-0.20：與該股票關聯間接或不明確

【限制條件】
- 若為傳聞或預測性內容，confidence 不得高於 0.8
- 若為極端分數（1、2、9、10），confidence 需 ≥ 0.7 且 ≤ 0.95
- 若判定為 5 分（無關），confidence 必須為 1.0

最終請將 confidence 限制在 0.0 ~ 1.0 範圍內,confidence 請保留到小數點後兩位

【輸出格式】（嚴格遵守，僅輸出 JSON，不加任何說明文字）
{
  "sentiment_score": <1 到 10 的整數>,
  "confidence": <0.0 到 1.0 的浮點數，代表你對此判斷的信心>
}
""".strip()

# 載入錯題本 (Few-Shot Examples)

ERROR_BOOK_FILE = '/content/drive/MyDrive/qwen2.5/error_book.json'
few_shot_prompt = ""

if os.path.exists(ERROR_BOOK_FILE):
    try:
        with open(ERROR_BOOK_FILE, 'r', encoding='utf-8') as f:
            error_examples = json.load(f)

        if error_examples:
            few_shot_prompt += "\n\n【⚠️ 過去判斷錯誤的歷史借鏡（請嚴格學習以下範例的評分邏輯）】\n"
            for i, ex in enumerate(error_examples, 1):
                few_shot_prompt += f"--- 範例 {i} ---\n"
                short_input = ex['input'][:150] + "..." if len(ex['input']) > 150 else ex['input']
                few_shot_prompt += f"新聞內容：{short_input}\n"
                few_shot_prompt += f"正確分數：{ex['correct_score']}\n"
                few_shot_prompt += f"判斷理由：{ex['reason']}\n"

        print(f"✅ 成功載入 {len(error_examples)} 筆錯題本範例！模型智商已升級。")
    except Exception as e:
        print(f"⚠️ 讀取錯題本失敗，將使用原始 Prompt。錯誤：{e}")

SYSTEM_PROMPT = BASE_SYSTEM_PROMPT + few_shot_prompt

print('✅ System Prompt 設定完成')
print('─' * 50)
print(SYSTEM_PROMPT)

✅ 成功載入 5 筆錯題本範例！模型智商已升級。
✅ System Prompt 設定完成
──────────────────────────────────────────────────
你是一位台灣股市量化分析師。
請分析以下新聞對「指定股票」的股價情緒影響，給出 1 到 10 的整數情緒分數。

【判斷維度（請綜合考量）】
- 影響程度：消息對基本面（營收、獲利、訂單、產能、競爭力）的衝擊大小
- 確定性：是「已發生/已證實」還是「預期/傳聞/可能」
- 影響範圍：僅該公司、整個產業、還是大盤層級
- 時間框架：短期（1個月內反映）還是長期（需數季才顯現）

【評分標準與範例】

 1 分：重大利空，股價可能大跌
   例：財務造假、重大違約/跳票、巨額虧損且超乎預期、下市/重整風險、
       董座或高層涉及重大刑事案件、工廠重大火災或停產且復原時間長、
       訴訟敗訴需鉅額賠償。

 2 分：明顯利空
   例：單季獲利或營收明顯不如市場預期、法說會大幅下修財測、
       重大客戶/訂單流失或延遲、信評或外資大幅調降評等與目標價、
       裁員或關廠等成本結構惡化訊號。

 3 分：輕微利空
   例：營收月減或年減但在合理範圍內、外資小幅調降目標價、
       原物料成本上升但公司表示可部分轉嫁、產業面出現溫和的負面雜音。

 4 分：偏空中性，預期有小幅負面壓力
   例：消息本身偏負面但對基本面影響極小或屬一次性費用、
       同業出現利空但對該公司影響有限、技術面或籌碼面的輕微負面訊息。

 5 分：完全中性，無明確影響
   例：例行性公告（股東會召開、董監事補選、一般人事異動）、
       與股價無直接關聯的企業形象/公益新聞、單純背景報導不含新資訊。

 6 分：偏多中性，長期可能正向但短期難反映
   例：長期利多但短期難反映在財報上（如簽署MOU、初期合作意向）、
       產業趨勢面偏正向但該公司受惠程度尚不明確、小幅度的正面雜音。

 7 分：輕微利多，已有可觀察到的正面訊號
   例：營收月增或年增且符合或略優於預期、取得新客戶或小型新訂單、
       外資小幅調升目標價、毛利率小幅改善。

 8 分：明顯利多
   例：單季獲利或營收明顯優於市場預期、法說會上修財測、
      

## 🔧 Step 4 — 輔助函式定義

包含：
- `build_prompt()` — 構建 Qwen ChatML 格式的 messages
- `parse_qwen_output()` — 容錯 JSON 解析（四層 fallback）

In [ ]:
import re


def build_prompt(stock_id: str, news_text: str) -> list:
    """
    構建 Qwen Chat 格式的 messages。
    Qwen2.5-Instruct 使用標準 ChatML 格式。
    """
    return [
        {'role': 'system', 'content': SYSTEM_PROMPT},
        {
            'role': 'user',
            'content': (
                f'分析目標股票代號：{stock_id}\n'
                f'新聞內容：{news_text}'
            ),
        },
    ]


def parse_qwen_output(raw_text: str) -> dict:
    """
    從 Qwen 輸出中解析 JSON，四層容錯機制：
      1. 直接解析標準 JSON
      2. 提取 Markdown code block 內容
      3. 抓第一個 {...} 區塊
      4. 正則抓數字（最後手段，信心設 0.5）
    """
    # 嘗試 1：直接解析
    try:
        return json.loads(raw_text.strip())
    except json.JSONDecodeError:
        pass

    # 嘗試 2：提取 ```json ... ``` 區塊
    match = re.search(r'```(?:json)?\s*(\{.*?\})\s*```', raw_text, re.DOTALL)
    if match:
        try:
            return json.loads(match.group(1))
        except json.JSONDecodeError:
            pass

    # 嘗試 3：抓第一個 {...} 區塊
    match = re.search(r'\{[^{}]+\}', raw_text, re.DOTALL)
    if match:
        try:
            return json.loads(match.group())
        except json.JSONDecodeError:
            pass

    # 嘗試 4：正則抓關鍵數字
    score_match = re.search(r'"sentiment_score"\s*:\s*(\d+)', raw_text)
    conf_match  = re.search(r'"confidence"\s*:\s*([\d.]+)', raw_text)
    if score_match:
        score = int(score_match.group(1))
        conf  = float(conf_match.group(1)) if conf_match else 0.5
        return {'sentiment_score': max(1, min(10, score)), 'confidence': conf}

    raise ValueError(f'無法解析輸出：{raw_text[:200]}')


print('✅ 輔助函式定義完成')


✅ 輔助函式定義完成


## 🏗️ Step 5 — 載入 vLLM 模型（bitsandbytes 動態 4-bit 量化）

> 你的合併模型是**未量化**的 14B 全精度模型，權重本身約 28GB，L4(24GB) 塞不下，載入就會 OOM。
> 這裡改用 vLLM 內建的 **bitsandbytes 動態量化**：載入時即時轉成 4-bit，不需要你另外跑一次 AWQ 量化流程，
> 顯存需求會降到約 9–10GB，L4 綽綽有餘。
>
> 代價：載入速度比原生 fp16 稍慢（要做 quant 轉換），且動態量化的精度/速度通常略遜於正規離線 AWQ，
> 但對於單純跑推論來說通常足夠好用。


In [ ]:
from vllm import LLM, SamplingParams

print('📦 正在載入 vLLM 引擎（bitsandbytes 4-bit 動態量化）...')
print(f'   模型 : {MODEL_ID}')
print(f'   最大序列長度 : {MAX_MODEL_LEN}')
print()

llm = LLM(
    model                  = MODEL_ID,
    quantization           = 'bitsandbytes',   # 動態 4-bit 量化，載入時即時轉換
    load_format            = 'bitsandbytes',   # 告訴 vLLM 用 bnb 方式讀取權重
    max_model_len          = MAX_MODEL_LEN,
    gpu_memory_utilization = GPU_MEMORY_UTIL,
    trust_remote_code      = True,             # Qwen 系列必須開啟
)

print('\n✅ 模型載入完成！')

# 採樣參數（推論任務偏向穩定，temperature 調低）
sampling_params = SamplingParams(
    temperature = 0.05,
    top_p       = 0.9,
    max_tokens  = 128,
    stop        = ['\n\n'],
)
print('✅ 採樣參數設定完成')
print(f'   temperature : {sampling_params.temperature}')
print(f'   max_tokens  : {sampling_params.max_tokens}')


INFO 07-16 11:26:12 [__init__.py:243] Automatically detected platform cuda.
📦 正在載入 vLLM 引擎（bitsandbytes 4-bit 動態量化）...
   模型 : /content/drive/MyDrive/qwen2.5/qwen_finetuned_merged
   最大序列長度 : 8192

INFO 07-16 11:26:23 [__init__.py:31] Available plugins for group vllm.general_plugins:
INFO 07-16 11:26:23 [__init__.py:33] - lora_filesystem_resolver -> vllm.plugins.lora_resolvers.filesystem_resolver:register_filesystem_resolver
INFO 07-16 11:26:23 [__init__.py:36] All plugins in this group will be loaded. Set `VLLM_PLUGINS` to control which plugins to load.
INFO 07-16 11:26:43 [config.py:793] This model supports multiple tasks: {'generate', 'embed', 'score', 'classify', 'reward'}. Defaulting to 'generate'.
WARNING 07-16 11:26:43 [config.py:907] bitsandbytes quantization is not fully optimized yet. The speed can be slower than non-quantized models.
INFO 07-16 11:26:43 [config.py:2118] Chunked prefill is enabled with max_num_batched_tokens=8192.
INFO 07-16 11:26:46 [core.py:438] Waiting for

Loading safetensors checkpoint shards:   0% Completed | 0/6 [00:00<?, ?it/s]


INFO 07-16 11:33:05 [gpu_model_runner.py:1549] Model loading took 9.3411 GiB and 377.352075 seconds
INFO 07-16 11:33:22 [backends.py:459] Using cache directory: /root/.cache/vllm/torch_compile_cache/2c6c4583c3/rank_0_0 for vLLM's torch.compile
INFO 07-16 11:33:22 [backends.py:469] Dynamo bytecode transform time: 17.12 s
INFO 07-16 11:33:33 [backends.py:132] Directly load the compiled graph(s) for shape None from the cache, took 9.175 s
INFO 07-16 11:33:37 [monitor.py:33] torch.compile takes 17.12 s in total
INFO 07-16 11:33:40 [kv_cache_utils.py:637] GPU KV cache size: 47,552 tokens
INFO 07-16 11:33:40 [kv_cache_utils.py:640] Maximum concurrency for 8,192 tokens per request: 5.80x
INFO 07-16 11:34:51 [gpu_model_runner.py:1933] Graph capturing finished in 71 secs, took 1.52 GiB
INFO 07-16 11:34:51 [core.py:167] init engine (profile, create kv cache, warmup model) took 106.71 seconds

✅ 模型載入完成！
✅ 採樣參數設定完成
   temperature : 0.05
   max_tokens  : 128


## Step 5.5 — 以實際 token 數截斷新聞內容

In [ ]:
from transformers import AutoTokenizer

# 用跟模型一致的 tokenizer 來量測 token 數（不是用字數估算）
tokenizer_for_len = AutoTokenizer.from_pretrained(MODEL_ID, trust_remote_code=True)

# 用「空新聞內容」量測 System Prompt + Qwen chat 模板固定會佔用多少 token
_probe_messages = build_prompt('0000', '')
_probe_ids = tokenizer_for_len.apply_chat_template(
    _probe_messages, tokenize=True, add_generation_prompt=True
)
FIXED_OVERHEAD_TOKENS = len(_probe_ids)

SAFETY_BUFFER = 64  # 額外預留，避免 tokenizer 估算跟 vLLM 實際計算有微小落差

# 新聞內容可用的 token 數 = 總長度上限 - 固定開銷(System Prompt+模板) - 輸出保留 - 安全緩衝
MAX_NEWS_TOKENS = MAX_MODEL_LEN - FIXED_OVERHEAD_TOKENS - sampling_params.max_tokens - SAFETY_BUFFER

print(f'📏 System Prompt + 模板固定開銷 : {FIXED_OVERHEAD_TOKENS} tokens')
print(f'📏 新聞內容可用上限            : {MAX_NEWS_TOKENS} tokens')

if MAX_NEWS_TOKENS <= 0:
    raise ValueError(
        f'MAX_MODEL_LEN({MAX_MODEL_LEN}) 太小，System Prompt 本身就已經吃滿了，'
        f'請調高 MAX_MODEL_LEN 或縮短 System Prompt。'
    )


def truncate_news_by_tokens(news_text: str, max_tokens: int = MAX_NEWS_TOKENS) -> str:
    """
    依「實際 token 數」截斷新聞內容，而非字數估算。
    超出上限才截斷，未超出則原樣返回。
    """
    ids = tokenizer_for_len.encode(news_text, add_special_tokens=False)
    if len(ids) <= max_tokens:
        return news_text
    truncated_ids = ids[:max_tokens]
    truncated_text = tokenizer_for_len.decode(truncated_ids, skip_special_tokens=True)
    return truncated_text + '\n\n[...系統提示：因原文過長，後續內容已由系統自動截斷...]'


print('✅ token-based 截斷函式設定完成')

📏 System Prompt + 模板固定開銷 : 2215 tokens
📏 新聞內容可用上限            : 5785 tokens
✅ token-based 截斷函式設定完成


## 🧪 Step 6 — 單筆測試（選用）

先跑一筆確認模型輸出格式正常，再進入批次推論，避免整批跑完才發現格式跑掉。

In [ ]:
test_stock = '2303'
test_news  = '聯電第三季營收優於市場預期，法人上修全年獲利預估。'

test_conv = build_prompt(test_stock, test_news)
test_output = llm.chat([test_conv], sampling_params=sampling_params)
raw = test_output[0].outputs[0].text.strip()

print('🔎 模型原始輸出：')
print(raw)
print()

try:
    parsed = parse_qwen_output(raw)
    print('✅ 解析成功：', parsed)
except Exception as e:
    print('❌ 解析失敗：', e)


INFO 07-16 11:34:55 [chat_utils.py:419] Detected the chat template content format to be 'string'. You can set `--chat-template-content-format` to override this.


Adding requests:   0%|          | 0/1 [00:00<?, ?it/s]

Processed prompts:   0%|          | 0/1 [00:00<?, ?it/s, est. speed input: 0.00 toks/s, output: 0.00 toks/s]

🔎 模型原始輸出：
{"sentiment_score": 7, "confidence": 0.9}

✅ 解析成功： {'sentiment_score': 7, 'confidence': 0.9}


## 🚀 Step 7 — 批次推論（主流程）

vLLM 會**自動並行處理**整個 batch，速度遠快於逐筆呼叫。
輸入檔案每行需為 JSON，至少包含 `stock`（股票代號）與 `input`（新聞內容）兩個欄位。

In [ ]:
from datetime import datetime
import time
import json

def inference (INPUT_FILE, OUTPUT_FILE):

  # ── 讀取所有資料 ──
  all_records = []
  with open(INPUT_FILE, 'r', encoding='utf-8') as f:
      for line in f:
          line = line.strip()
          if line:
              all_records.append(json.loads(line))

  total       = len(all_records)
  success_cnt = 0
  error_cnt   = 0
  start_time  = datetime.now()

  print(f'📊 共 {total} 筆資料，批次大小 {BATCH_SIZE}')
  print(f'🛡️ 已啟動 token-based 截斷防護：新聞內容上限 {MAX_NEWS_TOKENS} tokens')
  print('─' * 60)

  # ── 批次推論迴圈 ──
  with open(OUTPUT_FILE, 'w', encoding='utf-8') as f_out:

      for batch_start in range(0, total, BATCH_SIZE):
          batch         = all_records[batch_start : batch_start + BATCH_SIZE]
          batch_end_idx = batch_start + len(batch)

          # 構建 chat 格式的 conversations ── ⚡ 用實際 token 數截斷，而非字數估算
          conversations = []
          for r in batch:
              raw_input = r.get('input', '')

              news_token_ids = tokenizer_for_len.encode(raw_input, add_special_tokens=False)

              if len(news_token_ids) > MAX_NEWS_TOKENS:
                  safe_input = truncate_news_by_tokens(raw_input, MAX_NEWS_TOKENS)
                  print(
                      f"⚠️ [長度預警] 股票:{r['stock']} 的新聞過長 "
                      f"({len(news_token_ids)} tokens)，已截斷至 {MAX_NEWS_TOKENS} tokens。"
                  )
              else:
                  safe_input = raw_input

              conversations.append(build_prompt(r['stock'], safe_input))

          # vLLM 批次推論（自動套用 Qwen 的 chat template）
          outputs = llm.chat(conversations, sampling_params=sampling_params)

          for i, (record, output) in enumerate(zip(batch, outputs)):
              global_idx = batch_start + i + 1
              raw_text   = output.outputs[0].text.strip()

              max_retries = 3
              parse_success = False

              for attempt in range(max_retries):
                  try:
                      result = parse_qwen_output(raw_text)

                      score = max(1, min(10, int(result['sentiment_score'])))
                      conf  = max(0.0, min(1.0, float(result['confidence'])))

                      record['output'] = {
                          'sentiment_score': score,
                          'confidence'     : conf
                      }
                      success_cnt += 1
                      print(
                          f'✅ [{global_idx:>5}/{total}] '
                          f'股票:{record["stock"]:>6} | '
                          f'Qwen分數:{score:>2} | 信心:{conf:.2f}'
                      )

                      parse_success = True
                      break

                  except Exception as e:
                      print(f'⚠️ [{global_idx:>5}/{total}] 第 {attempt + 1} 次嘗試失敗：{e}，準備重試...')
                      time.sleep(2)

              # 如果 3 次都失敗，給予最乾淨的 null 預設值
              if not parse_success:
                  error_cnt += 1
                  record['output'] = {
                      'sentiment_score': None,
                      'confidence'     : None
                  }
                  print(f'❌ [{global_idx:>5}/{total}] 已達 3 次重試上限，放棄此筆資料，寫入 null')

              f_out.write(json.dumps(record, ensure_ascii=False) + '\n')

          f_out.flush()
          elapsed = (datetime.now() - start_time).total_seconds()
          print(f'  → 批次完成 [{batch_end_idx}/{total}]，累計耗時 {elapsed:.0f}s')

  # ── 最終統計 ──
  total_elapsed = (datetime.now() - start_time).total_seconds()
  print()
  print('=' * 60)
  print('🎉 推論完成！')
  print(f'   成功 : {success_cnt} 筆')
  print(f'   失敗 : {error_cnt} 筆')
  print(f'   耗時 : {total_elapsed:.0f}s（{total_elapsed/60:.1f} 分鐘）')
  print(f'   輸出 : {OUTPUT_FILE}')
  print('=' * 60)

In [ ]:
stockList = [2317, 2303, 2308, 2330, 2408, 2454, 2327, 3481, 3711, 6182]

for stock in stockList:
  # ── 檔案路徑 ───────────────────────────────────────────────
  INPUT_FILE  = f'/content/drive/MyDrive/qwen2.5/dataset/{stock}.jsonl'      # 待推論資料，需含 stock / input 欄位
  OUTPUT_FILE = f'/content/drive/MyDrive/qwen2.5/dataset/qwen_predictions_{stock}.jsonl'  # 推論結果輸出位置
  print (f'正在推論:{stock}')
  inference(INPUT_FILE, OUTPUT_FILE)

正在推論:2317
📊 共 3968 筆資料，批次大小 16
🛡️ 已啟動 token-based 截斷防護：新聞內容上限 5785 tokens
────────────────────────────────────────────────────────────


Adding requests:   0%|          | 0/16 [00:00<?, ?it/s]

Processed prompts:   0%|          | 0/16 [00:00<?, ?it/s, est. speed input: 0.00 toks/s, output: 0.00 toks/s]

✅ [    1/3968] 股票:  2317 | Qwen分數: 7 | 信心:0.90
✅ [    2/3968] 股票:  2317 | Qwen分數: 5 | 信心:0.90
✅ [    3/3968] 股票:  2317 | Qwen分數: 7 | 信心:0.90
✅ [    4/3968] 股票:  2317 | Qwen分數: 6 | 信心:0.90
✅ [    5/3968] 股票:  2317 | Qwen分數: 4 | 信心:0.85
✅ [    6/3968] 股票:  2317 | Qwen分數: 4 | 信心:0.90
✅ [    7/3968] 股票:  2317 | Qwen分數: 5 | 信心:1.00
✅ [    8/3968] 股票:  2317 | Qwen分數: 4 | 信心:0.90
✅ [    9/3968] 股票:  2317 | Qwen分數: 8 | 信心:0.90
✅ [   10/3968] 股票:  2317 | Qwen分數: 5 | 信心:0.95
✅ [   11/3968] 股票:  2317 | Qwen分數: 3 | 信心:0.85
✅ [   12/3968] 股票:  2317 | Qwen分數: 3 | 信心:0.85
✅ [   13/3968] 股票:  2317 | Qwen分數: 4 | 信心:0.85
✅ [   14/3968] 股票:  2317 | Qwen分數: 2 | 信心:0.90
✅ [   15/3968] 股票:  2317 | Qwen分數: 4 | 信心:0.85
✅ [   16/3968] 股票:  2317 | Qwen分數: 4 | 信心:0.85
  → 批次完成 [16/3968]，累計耗時 11s


Adding requests:   0%|          | 0/16 [00:00<?, ?it/s]

...

Processed prompts:   0%|          | 0/16 [00:00<?, ?it/s, est. speed input: 0.00 toks/s, output: 0.00 toks/s]

✅ [  225/246] 股票:  6182 | Qwen分數: 8 | 信心:0.90
✅ [  226/246] 股票:  6182 | Qwen分數: 8 | 信心:0.95
✅ [  227/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  228/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  229/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  230/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  231/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  232/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  233/246] 股票:  6182 | Qwen分數: 8 | 信心:0.90
✅ [  234/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  235/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  236/246] 股票:  6182 | Qwen分數: 8 | 信心:0.90
✅ [  237/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  238/246] 股票:  6182 | Qwen分數: 5 | 信心:0.90
✅ [  239/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  240/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
  → 批次完成 [240/246]，累計耗時 183s


Adding requests:   0%|          | 0/6 [00:00<?, ?it/s]

Processed prompts:   0%|          | 0/6 [00:00<?, ?it/s, est. speed input: 0.00 toks/s, output: 0.00 toks/s]

✅ [  241/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  242/246] 股票:  6182 | Qwen分數: 8 | 信心:0.90
✅ [  243/246] 股票:  6182 | Qwen分數: 6 | 信心:0.90
✅ [  244/246] 股票:  6182 | Qwen分數: 8 | 信心:0.90
✅ [  245/246] 股票:  6182 | Qwen分數: 7 | 信心:0.90
✅ [  246/246] 股票:  6182 | Qwen分數: 4 | 信心:0.90
  → 批次完成 [246/246]，累計耗時 191s

🎉 推論完成！
   成功 : 246 筆
   失敗 : 0 筆
   耗時 : 191s（3.2 分鐘）
   輸出 : /content/drive/MyDrive/qwen2.5/dataset/qwen_predictions_6182.jsonl


## ✅ 完成！

| 輸出檔案 | 說明 |
|----------|------|
| `qwen_predictions.jsonl` | 每筆資料的推論結果，原欄位保留並新增 `output` 欄位（含 `sentiment_score`、`confidence`）|

本程式僅涵蓋推論流程，不含與 Gemini 標注的一致性比對與視覺化，如需評估請沿用原本的訓練用 notebook 中對應步驟。

## step8 embedding

In [ ]:
from google.colab import drive
drive.mount('/content/drive')

'''
function ConnectButton(){
    console.log("Connect pushed");
    document.querySelector("#top-toolbar > colab-connect-button").shadowRoot.querySelector("#connect").click()
}
setInterval(ConnectButton, 60000);

for (let i = 1; i < 99999; i++) window.clearInterval(i);
console.log("已清除所有自動執行腳本");
'''


Mounted at /content/drive


'\nfunction ConnectButton(){\n    console.log("Connect pushed");\n    document.querySelector("#top-toolbar > colab-connect-button").shadowRoot.querySelector("#connect").click()\n}\nsetInterval(ConnectButton, 60000);\n\nfor (let i = 1; i < 99999; i++) window.clearInterval(i);\nconsole.log("已清除所有自動執行腳本");\n'

In [3]:
!pip install -U sentence-transformers -q

In [4]:
!pip install -U bitsandbytes>=0.46.1

In [1]:
import os
os.environ['PYTORCH_CUDA_ALLOC_CONF'] = 'expandable_segments:True'

import torch
from transformers import BitsAndBytesConfig
from sentence_transformers import SentenceTransformer

EMBED_MODEL_ID = 'Qwen/Qwen3-Embedding-8B'

# 8-bit 量化：權重從 ~16GB 降到 ~8GB
quant_config = BitsAndBytesConfig(load_in_8bit=True)

embed_model = SentenceTransformer(
    EMBED_MODEL_ID,
    model_kwargs={
        'quantization_config': quant_config,
        'torch_dtype': torch.float16,
    },
    tokenizer_kwargs={'padding_side': 'left'},
)

modules.json:   0%|          | 0.00/349 [00:00<?, ?B/s]

config_sentence_transformers.json:   0%|          | 0.00/215 [00:00<?, ?B/s]

README.md:   0%|          | 0.00/17.3k [00:00<?, ?B/s]

config.json:   0%|          | 0.00/729 [00:00<?, ?B/s]

model.safetensors.index.json:   0%|          | 0.00/30.4k [00:00<?, ?B/s]

...

vocab.json:   0%|          | 0.00/2.78M [00:00<?, ?B/s]

merges.txt:   0%|          | 0.00/1.67M [00:00<?, ?B/s]

tokenizer.json: reconstructing file:   0%|          |  0.00B / 11.4MB            

tokenizer.json: downloading bytes:           |  0.00B            

config.json:   0%|          | 0.00/313 [00:00<?, ?B/s]

## 測試輸入

## Step 8.4 — 讀取 輸出、補上 embedding、寫出新檔

In [2]:
import torch
import numpy as np

def embedding(SENTIMENT_FILE, EMBED_OUTPUT_FILE, truncate_dim=1024, batch_size=8, max_seq_length=2048):

    def truncate_and_renormalize(embs, dim):
        embs = np.array(embs)
        truncated = embs[:, :dim]
        norms = np.linalg.norm(truncated, axis=1, keepdims=True)
        return truncated / norms

    # ── 限制模型的最大輸入長度，避免單筆超長新聞把記憶體吃爆 ──
    embed_model.max_seq_length = max_seq_length

    # ── 讀取所有資料 ──
    all_records = []
    with open(SENTIMENT_FILE, 'r', encoding='utf-8') as f:
        for line in f:
            line = line.strip()
            if line:
                all_records.append(json.loads(line))

    total = len(all_records)

    # ── 斷點續跑：檢查輸出檔已經完成幾筆 ──
    done_count = 0
    if os.path.exists(EMBED_OUTPUT_FILE):
        with open(EMBED_OUTPUT_FILE, 'r', encoding='utf-8') as f:
            done_count = sum(1 for line in f if line.strip())
        print(f'📌 偵測到已完成 {done_count} 筆，將從第 {done_count + 1} 筆繼續')

    print(f'📊 共 {total} 筆資料，剩餘 {total - done_count} 筆需要補上 embedding（截斷維度：{truncate_dim}）')
    print('─' * 60)

    start_time = datetime.now()

    # ── 用 append 模式接續寫入，不覆蓋已完成的部分 ──
    with open(EMBED_OUTPUT_FILE, 'a', encoding='utf-8') as f_out:

        batch_start = done_count
        while batch_start < total:
            current_batch_size = batch_size
            batch = all_records[batch_start : batch_start + current_batch_size]
            texts = [r.get('input', '') for r in batch]

            # ── 這個 batch 嘗試失敗就自動降級重試，而不是整個崩潰 ──
            success = False
            while not success and current_batch_size >= 1:
                try:
                    sub_embeddings = embed_model.encode(
                        texts,
                        batch_size=current_batch_size,
                        normalize_embeddings=True,
                        show_progress_bar=False,
                    )
                    sub_embeddings = truncate_and_renormalize(sub_embeddings, truncate_dim)
                    success = True

                except torch.cuda.OutOfMemoryError:
                    torch.cuda.empty_cache()
                    current_batch_size = current_batch_size // 2
                    if current_batch_size >= 1:
                        print(f'⚠️ OOM，batch 降級為 {current_batch_size} 重試...')
                        batch = all_records[batch_start : batch_start + current_batch_size]
                        texts = [r.get('input', '') for r in batch]

            if not success:
                # 連 batch_size=1 都失敗，這筆資料本身有問題（可能超長），跳過並記錄
                print(f'❌ 索引 {batch_start} 即使 batch_size=1 仍 OOM，跳過此筆')
                record = all_records[batch_start]
                if 'output' not in record or record['output'] is None:
                    record['output'] = {}
                record['output']['embedding'] = None
                f_out.write(json.dumps(record, ensure_ascii=False) + '\n')
                batch_start += 1
                continue

            for record, emb in zip(batch, sub_embeddings):
                if 'output' not in record or record['output'] is None:
                    record['output'] = {}
                record['output']['embedding'] = emb.tolist()
                f_out.write(json.dumps(record, ensure_ascii=False) + '\n')

            f_out.flush()
            batch_start += len(batch)

            # ── 定期清快取，降低碎片化風險 ──
            if batch_start % (batch_size * 20) < batch_size:
                torch.cuda.empty_cache()

            elapsed = (datetime.now() - start_time).total_seconds()
            print(f'  → [{batch_start:>5}/{total}] 完成，累計耗時 {elapsed:.0f}s')

    print()
    print('=' * 60)
    print('🎉 Embedding 補完！')
    print(f'   輸出維度 : {truncate_dim}')
    print(f'   輸出 : {EMBED_OUTPUT_FILE}')
    print('=' * 60)

In [3]:
from datetime import datetime
import time
import json

stockList = [2317, 2303, 2308, 2330, 2408, 2454, 2327, 3481, 3711, 6182]
for stock in stockList:
  print(f'{stock}:\n')
  SENTIMENT_FILE = f'/content/drive/MyDrive/qwen2.5/dataset/qwen_predictions_{stock}.jsonl'
  EMBED_OUTPUT_FILE = f'/content/drive/MyDrive/qwen2.5/dataset/qwen_predictions_{stock}_with_embedding.jsonl'
  embedding(SENTIMENT_FILE, EMBED_OUTPUT_FILE)

2317:

📊 共 3968 筆資料，剩餘 3968 筆需要補上 embedding（截斷維度：1024）
────────────────────────────────────────────────────────────
  → [    8/3968] 完成，累計耗時 6s
  → [   16/3968] 完成，累計耗時 9s
  → [   24/3968] 完成，累計耗時 12s
  → [   32/3968] 完成，累計耗時 16s
  → [   40/3968] 完成，累計耗時 21s
  → [   48/3968] 完成，累計耗時 23s
  → [   56/3968] 完成，累計耗時 28s
  → [   64/3968] 完成，累計耗時 35s
  → [   72/3968] 完成，累計耗時 43s
  → [   80/3968] 完成，累計耗時 49s
  → [   88/3968] 完成，累計耗時 56s
  → [   96/3968] 完成，累計耗時 63s
  → [  104/3968] 完成，累計耗時 65s
  → [  112/3968] 完成，累計耗時 71s
  → [  120/3968] 完成，累計耗時 75s
  → [  128/3968] 完成，累計耗時 79s
  → [  136/3968] 完成，累計耗時 83s
  → [  144/3968] 完成，累計耗時 86s
  → [  152/3968] 完成，累計耗時 91s
  → [  160/3968] 完成，累計耗時 96s
  → [  168/3968] 完成，累計耗時 101s
  → [  176/3968] 完成，累計耗時 103s
  → [  184/3968] 完成，累計耗時 107s
  → [  192/3968] 完成，累計耗時 111s
  → [  200/3968] 完成，累計耗時 118s
  → [  208/3968] 完成，累計耗時 124s
  → [  216/3968] 完成，累計耗時 126s
  → [  224/3968] 完成，累計耗時 134s
  → [  232/3968] 完成，累計耗時 141s
  → [  240/3968] 完成，累計耗時 143s
  → [ 